# <center> ISEL - CSM </center>
## <center>Semestre 2023/24 </center>
###  <center> Trabalho 2 - Codificação de Sinais Multimédia</center>

Trabalho realizado por:
* João Ramos, numero <b> 50730 </b>
* Miguel Alcobia, numero <b> 50746 </b>
* Fábio Pestana, numero <b> 50756 </b>

<b> Turma 42D </b> <br></br>
<b> Docente: Gonçalo Valadão </b>

### 1.
Elabore uma função ``(gen_huff_table)`` que gere uma tabela com o código binário para cada símbolo de um
dado conjunto, usando o método de Huffman. Esta função deve ter como parâmetros de entrada um conjunto de
símbolos e as suas probabilidades (ou em alternativa pode usar o número de ocorrências de cada símbolo, dado
pelo seu histograma). Também pode em alternativa gerar não uma tabela mas outra estrutura de dados com os
códigos pretendidos (ex: dicionário)

In [15]:
import cv2 as cv
import numpy as np
import matplotlib.pyplot as plt
from time import time
import os
import math

# %matplotlib widget

def ordenar_por_underscore(valor):
    """Ordena uma sequência de acordo com o número de underscores.

    Args:
        valor (str): A sequência a ser ordenada.

    Returns:
        int: O número de underscores na sequência.
    """
    return str(valor).count("_")

def gen_huff_table(simb, prob, pb=1):
    """Gerar Tabela de Huffman

    Args:
        simb: lista de simbolos
        prob: lista de probabilidades ou frequências
        pb (int, optional): print boolean para imprimir a tabela (true) ou não (false). Defaults to 1.

    Returns:
        simb, bin_list, comp_bin: lista de simbolos, de codewords e do comprimento das codewords 
    """    
    # Converte os símbolos para strings
    simb = [str(s) for s in simb]
    
    # Associação das duas listas
    sync_list = list(zip(simb, prob))

    # Ordenação das probabilidades por ordem decrescente (reverse = True)
    # x[0] = simbs e x[1] = probs
    
    # Ordena pelas Probabilidades, caso sejam iguais, recorre ao número de "_" 
    # para acertar a ordenação, pois quer dizer que já houve união de simbolos
    sync_list.sort(key=lambda x: x[1], reverse=True)

    # Atualizar simb_ordenada e prob_ordenada
    simb_ordenada, prob_ordenada = zip(*sync_list)

    bin_list = [''] * len(simb)
    
    while len(prob_ordenada) > 1:
        """
        print(simb_ordenada)
        print(prob_ordenada)
        print(bin_list)
        print ("="*10)
        """
        for s in simb:
            if s in simb_ordenada[-1]:
                bin_list[simb.index(s)] = '1' + bin_list[simb.index(s)]
            elif s in simb_ordenada[-2]:
                bin_list[simb.index(s)] = '0' + bin_list[simb.index(s)]

        soma_ultimos_dois = np.sum(prob_ordenada[-2:])
        prob_ordenada = prob_ordenada[:-2] + (soma_ultimos_dois,)

        # Atualizar a simb_ordenada com os valores concatenados sync_list
        simb_ordenada = simb_ordenada[:-2] + (str(simb_ordenada[-2]) + "_" + str(simb_ordenada[-1]),)

        # Reordenar simb_ordenada e prob_ordenada
        # Junta as listas
        sync_list = list(zip(simb_ordenada, prob_ordenada))
        # x[0] = simbs e x[1] = probs
        sync_list.sort(key=lambda x: (x[0], ordenar_por_underscore(x[1])), reverse=True)
        sync_list.sort(key=lambda x: x[1], reverse=True)    
        simb_ordenada, prob_ordenada = zip(*sync_list)

    """
    print(simb_ordenada)
    print(prob_ordenada)
    print(bin_list)
    print ("="*10)
    """
    comp_bin = []
    for i in range(len(bin_list)):
        comp_bin.append(len(bin_list[i]))

    # TABELA
    if pb == 1:
        max_length_symb = max(len(s) for s in simb) + 15
        max_length_prob = max(len(str(p)) for p in prob) + 15
        max_length_cb = max(len(cb) for cb in bin_list) + 15

        print("{:<{width_symb}} {:<{width_prob}} {:<{width_cb}} {:<15} {:<15}".format(
            "Simb", "Prob/Freq", "Codeword", "Comp Bits", "Total bits", 
            width_symb=max_length_symb, width_prob=max_length_prob, width_cb=max_length_cb))

        for i in range(len(simb)):
            print("{:<{width_symb}} {:<{width_prob}} {:<{width_cb}} {:<15} {:<15}".format(
                simb[i], prob[i], bin_list[i], len(bin_list[i]), len(bin_list[i]) * int(bin_list[i]), 
                width_symb=max_length_symb, width_prob=max_length_prob, width_cb=max_length_cb))
    
    return simb, bin_list, comp_bin


# Exemplo de utilização:
#symbols = [2, 20, 30, 3, 23]
symbols = ['A', 'B', 'C', 'D', 'E']
probabilities = [0.4, 0.2, 0.2, 0.1, 0.1]

#symb2 = ['A', 'B', 'C']
#prob2 = [0.6, 0.3, 0.1]

gen_huff_table(symbols, probabilities)
#gen_huff_table(symb2, prob2)


Simb             Prob/Freq          Codeword           Comp Bits       Total bits     
A                0.4                00                 2               0              
B                0.2                11                 2               22             
C                0.2                10                 2               20             
D                0.1                010                3               30             
E                0.1                011                3               33             


(['A', 'B', 'C', 'D', 'E'], ['00', '11', '10', '010', '011'], [2, 2, 2, 3, 3])

> Comentários:

A função começa por tornar todos os elementos da lista de símbolos em strings, o que é útil quando os símbolos são números.<br>
Depois as listas dos símbolos e das probabilidades são unidas, resultando na ``sync_list``. Esta última lista é ordenada por forma decresente em relação às probabilidades e, por fim, voltamos a separar as listas que compõem ``sync_list`` e cria-se uma lista (``bin_list``) que terá os códigos que Huffman.<br>
No ciclco while, que tem como condição o comprimento da lista de probabilidades ser maior que 1, começamos por percorrer a lista de símbolos. Se o simbolo estiver no último índice da lista é acresentado 1 ao código de Huffman e se estiver no penúltimo recebe um 0.<br>
Atualiza-se as listas dos símbolos e das probabilidades, somando as últimas duas probablidades, e concatenando os respetivos símbolos.<br>
Por fim, cria-se a lista ``comp_bin``, na qual cada índice é preenchiado pelo comprimento do código situado no mesmo índice na ``bin_list``.

### 2.
Elabore uma função ``(encode_huff)`` que dada uma mensagem (sequência de símbolos) e a tabela da ponto anterior, retorne uma sequência de bits com a mensagem codificada.

In [16]:

def count_freq_simb(msg):
    """Contar frequência por simbolos

    Args:
        msg: mensagem

    Returns:
        simbs, freqs: lista de simbolos na mensagem, lista da respetiva frequência
    """
    # Ver a frequência dos simbolos
    frequencia = {}
    for simb in msg:
        if simb in frequencia:
            frequencia[simb] += 1
        else:
            frequencia[simb] = 1
    
    simbs = []
    freqs = []

    for simb, freq in frequencia.items():
        simbs.append(simb)
        freqs.append(freq)

    return simbs, freqs

def encode_huff(msg, tabela):
    """Codifica uma mensagem com a tabela de Huffman

    Args:
        msg: mensagem a codificar
        tabela: Tabela de Huffman da mensagem

    Returns:
        msg_code: mensagem codificado
    """
    if not all(isinstance(s, str) for s in msg):
        msg = [str(elemento) for elemento in msg]

    bin_list = tabela[1]
    comp_bin = tabela[2]
    simbs = count_freq_simb(msg)[0]
    msg_code = ""
    
    for s in msg:
        #idx = simbs.index(i)
        #msg_code += bin_list[idx]
        if s.isalpha():
            symb_code = bin(ord(s))[2:].zfill(8)
        else:
            symb_code = bin(int(s))[2:].zfill(8)
            
        #code_comp = bin(len(code[i]))[2:].zfill(5)
        code_comp = bin(comp_bin[simbs.index(s)])[2:].zfill(8)
        code_bin = bin_list[simbs.index(s)]
        
        msg_code += str(symb_code) + str(code_comp) + str(code_bin)

    return msg_code


mensagem ="AABCBAD"

simbs = count_freq_simb(mensagem)[0]
freqs = count_freq_simb(mensagem)[1]
tabela = gen_huff_table(simbs, freqs, 1)

msg_cod = encode_huff(mensagem, tabela)
print(msg_cod)

Simb             Prob/Freq        Codeword           Comp Bits       Total bits     
A                3                1                  1               1              
B                2                01                 2               2              
C                1                000                3               0              
D                1                001                3               3              
01000001000000011010000010000000110100001000000010010100001100000011000010000100000001001010000010000000110100010000000011001


> Comentário:    

Para codificar as mensagens, voltamos a verificar se todos os caracteres da mensagem são strings. Da tabela que a função recebe, extraímos a lista com os códigos e a que tem o comprimento destes, já a lista de simbolos é criada recorrendo à função count_freq_simb() que conta a frequência de cada simbolo numa mensagem.
Em seguida, percorremos a mensagem e para cada simbolo, fazemos a seguinte codificação:<br>
* 1 byte para binário do número ou para o binário do código ASCII (caso seja letra)
* 1 byte para o comprimento da codeword
* x bits para a codeword (sem qualquer alteração)<br>

Estas codificações de cada simbolo são concatenadas na string msg_code que é o retorno final da função.

### 3.
Elabore uma função ``(decode_huff)`` que dada uma sequência de bits (mensagem codificada) e a tabela do ponto 1, retorne uma sequência de símbolos (mensagem descodificada). Garanta que a mensagem retornada por esta função é igual à mensagem que é dada como parâmetro de entrada da função ``encode_huff``.

In [17]:
def split_data(msg, sb=0, tb=0, n_simbs=None):
    """Split Data

    Args:
        msg: mensagem
        sb (int, optional): string boolean, ver as letras em vez do código ASCII (true), ou não (false). Defaults to 0.
        tb (int, optional): together boolean, ativa o modo together. Defaults to 0.
        n_simbs (int, optional): número de símbolos da tabela. Defaults to None.

    Returns:
        simbs, code_comps, codes, mensagem (se tb=1 e len(simbs)==n_simbs)
    """
    simbs = []
    code_comps = []
    codes = []
    mensagem = ""

    i = 0
    while i < len(msg):
        # Extrair o símbolo (8 bits)
        if sb == 1:
            simb = chr(int(msg[i:i+8], 2))
        else:
            simb = int(msg[i:i+8], 2)
        simbs.append(simb)

        # Extrair o comprimento do código de Huffman (5 bits)
        code_comp = int(msg[i+8:i+16], 2)
        code_comps.append(code_comp)

        # Extrair o código de Huffman do símbolo
        code = msg[i+16:i+16+code_comp]
        codes.append(code)

        # Atualizar o índice para a próxima iteração
        i += 16 + code_comp

        # Verificar se o modo together está ativo e se o número de símbolos foi atingido
        if tb == 1 and len(simbs) == n_simbs:
            mensagem = msg[i:]  # Restante da mensagem
            break

    if tb == 1 and len(simbs) == n_simbs:
        return simbs, code_comps, codes, mensagem
    else:
        return simbs, code_comps, codes


def decode_huff(seq_bits, tabela, sb=0):
    """Descodifica uma sequência de bits com a tabela de Huffman

    Args:
        seq_bit: sequência a descodificar
        tabela: tabela a utilizar para a descodificação
        sb (int, optional): string boolean, ver as letras em vez do código ASCII (true), ou não (false). Defaults to 0.

    Returns:
        seq_simb: sequência dos símbolos resultantes da descodificação
    """
    simbs = tabela[0]
    bin_list = tabela[1]

    if isinstance(bin_list, np.ndarray):
        bin_list = bin_list.tolist()

    #seq_simb = ""
    seq_simb = []
    
    codes = split_data(seq_bits)[2]
    #print(codes)
    for i in range(len(codes)):
        idx_simb = bin_list.index(codes[i])
        seq_simb.append(simbs[idx_simb])
    
    #seq_simb = seq_simb[:-1]
    return seq_simb


msg_descod = decode_huff(msg_cod, tabela, 1)
print(msg_descod)
md=""
for s in msg_descod:
    md+=s
print("A mensagem descodificada é igual à do ponto 2? ", md == mensagem)

['A', 'A', 'B', 'C', 'B', 'A', 'D']
A mensagem descodificada é igual à do ponto 2?  True


>Comentário:

Extrai-se a lista de simbolos e a das respetivas codeword a partir da tabela que a função recebe. Convertemos a ``bin_list`` para lista, caso esta seja numpy array.<br>
Os códigos associados à mensagem, são obtidos a partir da função ``split_data()`` que descodifica e separa as informações de um simbolo que foi submetido à codificação referida acima.<br>
Por fim, percorremos a lista de códigos resultante da ``split_data()``, comparamos com os códigos fornecidos pela tabela e o símbolo associado a cada codeword é posto numa lista (``seq_simb``) que é retornada no final.

### 4.
Elabore uma função ``(encode_table)`` que dada a tabela de Huffman do ponto 1, retorna uma sequência de bits correspondente à tabela codificada. Acrescente esta sequência binária à obtida no ponto 2.

In [18]:
def remainder_next_mult8(num):
    """Resto para o próximo Múltiplo de 8

    Args:
        num: número para o qual se quer o resto para o resultado

    Returns:
        resto para o próximo múltiplo de 8
    """
    # Exemplo: (num = 73)
    # 73 % 8 = 1
    # 8 - 1 = 7 - > return 7
    # 73 + 7 = 80
    return (8 - (num % 8))

def encode_table(table):
    """Codifica uma Tabela de Huffman

    Args:
        table: Tabela que se pretende codificar
    
    Returns:
        str_table: Tabela codificada
    """
    
    symb = table[0] # simbolos da tabela
    #code = table[1] # respetivos códigos dos simbolos
    
    # string para guardar a sequência a retornar
    str_table = ''

    # tamano da tabela já em binário com 8 bits de comprimento
    if len(symb) == 256:
        table_size = "0".zfill(8)
    else:
        # linha que estava antes do TESTE
        table_size = bin(len(symb))[2:].zfill(8)

    # Table Header
    str_table += str(table_size)
    # Body Table 
    body_table = encode_huff(symb, table)

    str_table += body_table
    
    # Msg Header
    all_filler_bits = remainder_next_mult8(len(str_table))
    #print("Bits para chegar a 8 bits: "+ str(all_filler_bits))

    num_filler_bits = all_filler_bits - 3
    if num_filler_bits < 0:
        num_filler_bits = all_filler_bits + 5
    #print("Número de bits filler (sem header): " + str(num_filler_bits) + "("+ str(all_filler_bits) + " - 3)")
    
    idx_filler = bin(num_filler_bits)[2:].zfill(3)
    #print("Número de bits filler em bin (header): " + str(idx_filler))
    
    str_table = str(idx_filler) + "0"*num_filler_bits + str_table


    #print(str_table)
    #print(len(str_table)%8 == 0)

    return str_table


tabela_cod = encode_table(tabela)
print(tabela_cod)

1000000000001000100000100000001101000010000000100101000011000000110000100010000000011001


> Comentários:

O protocolo usado para codificar a tabela foi o seguinte:
* 3 bits para o header que informa o número de bits filler existentes
* n bits filler
* 8 bits para o tamanho da tabela
* Repete-se o protocolo do ponto 2 para cada simbolo<br>
bits filler = quantos bits são necessários para a quantidade de bits total ser múltipla de 8

A lista de simbolos é extraida da tabela fornecida à função e com o seu comprimento chegamos ao tamanho da tabela. Se este for igual a 256, o tamanho da tabela é codificado com 1 byte a 0's, caso contrário o byte é preenchido com o binário correspondente ao tamanho da tabela.
O corpo da tabela, os simbolos e respetivas informações, são codificados usando a função ``encode_huff()`` do ponto 2.
Esta informação é unida na string ``str_table``.

Para o header dos bits filler e os prórprios bits filler, começamos por ver quantos bits faltam à ``str_table`` para que o seu tamanho seja múltiplo de 8 recorrendo à ``remainder_next_mult8()``. A este resultado subtraimos 3 obtendo ``num_filler_bits``, porque 3 bits serão para o header; porém se depois desta subtração o resultado for negativo, ``num_filler_bits`` passa a ter o resultado de ``remainder_next_mult8() + 5``:

>Exemplo:<br>Bits para chegar a 8 bits: 2<br>Número de bits filler (sem header): -1(2 - 3)<br>-1+5=6 e 6+2=8<br><br>h = header<br>f = filler<br>hhhffffffff

No final a ``str_table`` é atualizada da forma devida com esta informação.

### 5.
Elabore uma função ``(write2file)`` que dada uma sequência de bits (mensagem codificada) e o nome do ficheiro, escreva a sequência de bits para o ficheiro.

In [19]:
def write2file(seq_bits, file_name):
    """Grava um sequência de bits para um ficheiro

    Args:
        seq_bits: Sequência de bits a gravar no ficheiro
        file_name: Nome do ficheiro, onde se vai gravar a sequência
    """

    file = open(file_name, 'w')
    for bit in seq_bits:
        file.write(str(bit))
    file.close()

# Exemplo de uso:
seq_bits = tabela_cod  # Sequência de bits conforme o protocolo
file_name = "tabela_cod.txt"  # Nome do arquivo de saída
write2file(seq_bits+msg_cod, file_name)


> Comentários:

Esta função grava cada bit da sequência de bits passada como argumento para um ficheiro com o nome igual ao de ``file_name``.

### 6.
Elabore uma função ``(read_file)`` que dado o nome do ficheiro, leia uma sequência de bits (tabela codificada e mensagem codificada) contida no ficheiro e que descodifique a tabela, retorne a tabela descodificada bem como a sequência binária correspondente à mensagem codificada.


In [20]:
def read_file(file_name, pb=0, sb=0):
    """Read File

    Args:
        file_name: ficheiro a ler
        pb (int, optional): print boolean. Defaults to 0.
        sb (int, optional): string boolean. Defaults to 0.

    Returns:
        Lista de Simbolos, Codewords, Comprimento das codewords e a mensagem
    """

    with open(file_name, "r") as file:
        msg = file.read()
        #print("Mensagem: " + msg)
        
        filler_bits = msg[:3]
        num_filler_bits = int(filler_bits, 2)
        start_idx = 3 + num_filler_bits # [0, 1, 2, num_filler_bits]
        
        table_size = int(msg[start_idx:start_idx+8], 2)
        if table_size == 0:
            table_size = 256
            
        print("Table Size", table_size)
        n_msg = msg[start_idx+8:]
        #print("Nova Mensagem: " + n_msg)
        simb, comp_bits, codeword, msg_split = split_data(n_msg, sb, 1, table_size)
    
    if pb == 1:
        # Encontrar o comprimento máximo de cada coluna
        max_length_simb = max(len(str(x)) for x in simb) + 15
        max_length_codeword = max(len(x) for x in codeword) + 15
        max_length_comp_bits = max(len(str(x)) for x in comp_bits) + 15

        print("{:<{}} {:<{}} {:<{}}".format(
                "Simb", max_length_simb, "Codeword", max_length_codeword, "Comp Bits", max_length_comp_bits))
            
        for i in range(len(simb)):
            print("{:<{}} {:<{}} {:<{}}".format(
            simb[i], max_length_simb, codeword[i], max_length_codeword, comp_bits[i], max_length_comp_bits))

        if msg_split is not None:
            print("\n Mensagem: ", msg_split,"\n")
        
        print("\nNOTA: Conversão para ASCII desligada") if sb == 0 else ""
    
    if msg_split is not None:
        return np.stack((simb, codeword, comp_bits)), msg_split
    else:
        return np.stack((simb, codeword, comp_bits))

read_file("tabela_cod.txt", 1, 1)

Table Size 4
Simb             Codeword           Comp Bits       
A                1                  1               
B                01                 2               
C                000                3               
D                001                3               

 Mensagem:  01000001000000011010000010000000110100001000000010010100001100000011000010000100000001001010000010000000110100010000000011001 



(array([['A', 'B', 'C', 'D'],
        ['1', '01', '000', '001'],
        ['1', '2', '3', '3']], dtype='<U11'),
 '01000001000000011010000010000000110100001000000010010100001100000011000010000100000001001010000010000000110100010000000011001')

> Comentários:

Abre um ficheiro com uma tabela codificada com o protocolo apresentado no ponto 4 e reconstrói a respetiva tabela de Huffman

### 7.
Teste as funções elaboradas usando para o efeito os seguintes ficheiros com diferentes tipos de média. Adicionalmente, pode usar
mais outros ficheiros à sua escolha que achar pertinentes.

a) Gere o código usando a função realizada no ponto 1. Meça o tempo que demora a função.

In [21]:
# Função para deixar o array de simbolos sem simbolos repetidos

def unique(lista):
    """Retorna array com elementos únicos

    Args:
        lista: lista com elementos repetidos

    Returns:
        unique_list: array sem elementos repetidos
    """
    unique_list = []
 
    for x in lista:
        if x not in unique_list:
            unique_list.append(x)
    return unique_list

In [22]:
# Ler um dos ficheiros
file = "LenaGray.tif"
#file = "LenaColor.tif"
#file = "DecUniversalDH.pdf"
#file = "DecUniversalDH.txt"
#file = "HenryMancini-PinkPanther30s.mp3"
#file = "HenryMancini-PinkPantherC.mid"

x = np.fromfile(file,dtype="uint8")

x.tolist()

x_simb, x_hist = count_freq_simb(x)

# Gerar o código de Huffman
t0 = time()
tabela_codigo = gen_huff_table(x_simb,x_hist)
print("Teste Size", len(tabela_codigo[0]))
t1 = time()
print("time:", t1-t0)

Simb               Prob/Freq           Codeword                                                                                                                                                                                                                                            Comp Bits       Total bits     
73                 679                 1111010001011101                                                                                                                                                                                                                                    16              17776160016177616
42                 1090                111000110100010000011                                                                                                                                                                                                                               21              2331002312100210000231
0                  5487                1111111

b) Meça a entropia e o número médio de bits por símbolo. Calcule a eficiência.

In [23]:
# Calcular probabilidade

def calc_prob(simbs, freqs):
    """Calcula Probabilidade

    Args:
        simbs: lista de simbolos
        freqs: lista de frequências

    Returns:
        probs: array com as probabilidades
    """
    probs = []
    for i in range(len(simbs)):
        prob = freqs[i]/np.sum(np.fromiter((f for f in freqs), dtype=float))
        probs.append(prob)
    return probs

def calc_entropy(probs):
    """Calcula Entropia

    Args:
        probs: lista com probabilidade

    Returns:
        entropy: valor de entropia
    """
    entropy = -1*np.sum(np.fromiter((p * math.log2(p) for p in probs), dtype=float))
    return entropy

def calc_num_med_bits(probs):
    """Calcula Número Médio de Bits

    Args:
        probs: lista com probabilidade

    Returns:
        num_med_bits: número médio de bits
    """
    num_med_bits = np.sum(np.fromiter((p * math.log2(1/p) for p in probs), dtype=float))
    return num_med_bits

def calc_eficiencia(entropy, num_med_bits):
    """Calcula Eficiência

    Args:
        entropy: valor de entropia
        num_med_bits: valor do número médio de bits

    Returns:
        eficiência
    """
    return entropy/ num_med_bits


x_prob = calc_prob(x_simb, x_hist)
x_entropy = calc_entropy(x_prob)
x_num_med_bits = calc_num_med_bits(x_prob)

print("Probabilidades de ocorrência de cada símbolo:", x_prob)
sum = np.sum(np.fromiter((i for i in x_prob), dtype=float))
print("Soma das Probabilidades:", round(sum, 2)) 
print("Entropia:", x_entropy)
print("Número médio de bits por símbolo:", x_num_med_bits)
print("Eficiência:", calc_eficiencia(x_entropy, x_num_med_bits))

t2 = time()
print("time:", t2-t1)

Probabilidades de ocorrência de cada símbolo: [0.0032314560112696434, 0.005187462521773065, 0.026113400786209915, 0.00410237861813613, 0.002527103301891282, 0.010370165903617898, 0.014296456344409438, 0.0059013335110078904, 0.00616308620706066, 0.004792453907729795, 0.00583470555201264, 0.0035217635468918055, 0.00717202387184588, 0.0031791054720590895, 0.0192316844499862, 0.00987045621115352, 0.001989320490001047, 0.001851305432082314, 0.004435518413112382, 0.006263028145553536, 0.0015276839169625265, 0.0035503183864611988, 0.0038929764612939148, 0.009251768020483338, 0.004963782945146153, 0.00526360876062478, 0.009884733630938216, 0.0032885656904084294, 0.0015562387565319195, 0.00508752058328019, 0.0018798602716517071, 0.004564015191174651, 0.0049066732660073675, 0.015909804780080142, 0.003112477513063839, 0.011103073452565653, 0.0019179333910775646, 0.0026984323393076403, 0.0026984323393076403, 0.00789541314093717, 0.0023081828651926022, 0.001256412941053293, 0.004859081866725045, 0.

c) Faça a codificação da mensagem contida no ficheiro (usando a função realizada no ponto 2). Meça o tempo que a função demora a fazer a codificação.

In [24]:
seq_bit_0 = encode_huff(x, tabela_codigo) # mensagem
#print(seq_bit_0)
seq_bit_1 = encode_table(tabela_codigo)
t3 = time()
print("time:", t3-t2)

time: 2.3003668785095215


d) Grave um ficheiro com a mensagem codificada, usando a função realizada no ponto 4. Veja o tamanho do ficheiro.

In [25]:
#escrever ficheiro

filename = "teste_7d.txt"
#write2file(seq_bit_0, "seqBit.txt")
write2file(seq_bit_1+seq_bit_0, filename)
print("Tamanho do ficheiro:", os.path.getsize(filename), "bytes")
t4 = time()
print("time:", t4-t3)

Tamanho do ficheiro: 9856776 bytes
time: 3.1623623371124268


e) Leia do ficheiro o conjunto de bits, usando a função realizada no ponto 5.

In [26]:
# Ler ficheiro e descodificar a tabela
tabela_descode, mensagem_code = read_file(filename, 1)
print("Comp. da Codeword mais longa:", len(max((tabela_descode[1]), key=len)))
t5 = time()
print("time:", t5-t4)

Table Size 256
Simb               Codeword                                                                                                                                                                                                                                            Comp Bits         
73                 1111010001011101                                                                                                                                                                                                                                    16                
42                 111000110100010000011                                                                                                                                                                                                                               21                
0                  111111111111111110101111111011111000010111110111111111101010101111101000111101001111001111001111101111001111111100101110

f) Faça a descodificação da mensagem (usando a função realizada no ponto 3.) Meça o tempo que a função demora a fazer a descodificação.

In [27]:
#descodificar a mensagem
m = decode_huff(mensagem_code, tabela_descode, 1)
print(m)
t6 = time()
print("time:", t6-t5)

['73', '73', '42', '0', '52', '51', '3', '0', '128', '40', '128', '0', '7', '248', '5', '246', '6', '127', '1', '31', '128', '23', '243', '236', '16', '253', '125', '128', '159', '224', '80', '3', '228', '4', '254', '1', '191', '162', '239', '208', '35', '248', '1', '23', '2', '63', '64', '175', '224', '75', '228', '13', '4', '0', '129', '159', '241', '215', '232', '8', '1', '14', '124', '191', '223', '111', '247', '152', '0', '14', '242', '122', '189', '95', '239', '71', '184', '1', '250', '254', '126', '2', '64', '207', '144', '60', '112', '3', '3', '127', '201', '223', '207', '250', '92', '82', '8', '255', '0', '0', '98', '81', '170', '136', '2', '129', '46', '1', '84', '168', '96', '48', '44', '101', '242', '10', '130', '128', '223', '175', '240', '24', '2', '84', '250', '137', '129', '96', '175', '208', '53', '162', '202', '252', '4', '0', '95', '128', '39', '236', '248', '4', '4', '124', '88', '168', '175', '251', '164', '133', '254', '7', '140', '63', '159', '64', '103', '228', 

g) Compare a mensagem descodificada com a original e verifique que são iguais (erro nulo).

In [28]:
msg_og = x.tolist()
print(msg_og)

msg_dc = list(map(int, m))
#print(msg_dc)

mensagem_decode = decode_huff(mensagem_code, tabela_descode)
mensagem_decode = [int(s) for s in mensagem_decode]

print("A mensagem orignal é igual à descodificada (função 3):", msg_og == msg_dc)

print("A mensagem orignal é igual à descodificada (função 6):", msg_og == mensagem_decode)


# DESCOMENTAR NO CASO DE TEXTO
#msg_dc_chr = [chr(i) for i in msg_dc]
#print(msg_dc_chr)

[73, 73, 42, 0, 52, 51, 3, 0, 128, 40, 128, 0, 7, 248, 5, 246, 6, 127, 1, 31, 128, 23, 243, 236, 16, 253, 125, 128, 159, 224, 80, 3, 228, 4, 254, 1, 191, 162, 239, 208, 35, 248, 1, 23, 2, 63, 64, 175, 224, 75, 228, 13, 4, 0, 129, 159, 241, 215, 232, 8, 1, 14, 124, 191, 223, 111, 247, 152, 0, 14, 242, 122, 189, 95, 239, 71, 184, 1, 250, 254, 126, 2, 64, 207, 144, 60, 112, 3, 3, 127, 201, 223, 207, 250, 92, 82, 8, 255, 0, 0, 98, 81, 170, 136, 2, 129, 46, 1, 84, 168, 96, 48, 44, 101, 242, 10, 130, 128, 223, 175, 240, 24, 2, 84, 250, 137, 129, 96, 175, 208, 53, 162, 202, 252, 4, 0, 95, 128, 39, 236, 248, 4, 4, 124, 88, 168, 175, 251, 164, 133, 254, 7, 140, 63, 159, 64, 103, 228, 142, 162, 1, 126, 128, 240, 175, 231, 245, 30, 197, 71, 198, 227, 106, 81, 124, 100, 130, 228, 3, 0, 220, 164, 116, 185, 117, 200, 2, 7, 124, 63, 193, 15, 185, 253, 149, 246, 4, 163, 211, 0, 111, 247, 238, 2, 63, 11, 164, 93, 40, 224, 40, 204, 99, 19, 43, 125, 97, 223, 96, 0, 36, 82, 241, 30, 177, 239, 0, 81, 29, 9